In [1]:
from spectrascope.ss_classification import * 

In [2]:
from spectrascope.plot_spectral_features import plot_spectral_features as psf 
from spectrascope.plot_spectral_features import plot_model as pm 

### 1. Load Data (X,y)

In [3]:
fnX = "/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/tests/test_files/X_testfile.npy"
fny = "/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/tests/test_files/y_testfile.npy"
X = np.load(fnX)
y = np.load(fny)

fn = '/Users/amalyajohnson/Desktop/Spectrascope/Datasets/XAS_PDF/Ti/processed_billinge.json'
data = pd.read_json(fn)
structures = data['structure'].apply(lambda x : Structure.from_dict(x))
structures = structures.to_numpy()
mpids = data['mp_id'].to_list()

info = BinaryClassifications(
    structures, mpids, X=X, y=y, specnames=["pdf", "xanes"], yname="nn", random_seed=10, generate_dict=False
)

info = SpectraScope(X=X, y=y, specnames=["pdf", "xanes"], yname="nn", random_seed=10)

saving to /examples/models, change save_path kwarg if youd like to change
saving to /examples/models, change save_path kwarg if youd like to change


In [14]:
#small dataset 
# X = X[:, :10, :]
# y = y[:10]

# structures = np.load("/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/tests/test_files/structures.npy", allow_pickle=True)
# mpids = np.load("/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/tests/test_files/mpids.npy")
# mpids = list(mpids)

In [4]:
info.add_x_axis(specname='xanes', value=np.linspace(4969.0, 5021.0, 200))
info.add_x_axis(specname='pdf', value=np.linspace(0,10,200))


info.add_spectral_feature('xanes', 'pointwise_features', xrange = info.xanes_xaxis)
info.add_spectral_feature('pdf', 'pointwise_features', xrange = info.pdf_xaxis)

In [16]:
%load_ext autoreload
%autoreload 2

The autoreload extension is already loaded. To reload it, use:
  %reload_ext autoreload


In [5]:
nspecs = len(info.specnames)

fig1 = make_subplots(
    rows=1, cols=nspecs, subplot_titles = info.specnames, horizontal_spacing = 0.15
    )

for i,spec in enumerate(info.specnames): 
    xaxis_label='x' # input 
    yaxis_label = 'y' # input 
    x = getattr(info, f'{spec}_xaxis')
    y = getattr(info, f'{spec}_pointwise_features')
    plotter = psf(xaxis=x, arr=y, xaxis_label=xaxis_label, yaxis_label=yaxis_label, name='', fig=fig1, row=1, col=i + 1)
    plotter.plot_raw_spec()

fig1.show()

In [6]:

info.add_spectral_feature('xanes', 'polynomial_featuresall')
info.add_spectral_feature('xanes', 'polynomial_featuresN', N=5)
info.add_spectral_feature('xanes', 'cwt')
info.add_spectral_feature('xanes', 'featureagg', n_clusters=10)
info.add_spectral_feature('xanes', 'pca', n_components=100)
info.add_spectral_feature('xanes', 'cdf')
info.add_spectral_feature('xanes', 'fft_features', xrange=info.xanes_xaxis)
info.add_spectral_feature('xanes', 'tsne', n_components=2)

In [8]:
from itertools import product

In [9]:
features = ['polynomial_featuresall', 'cdf', 'cwt', 'pca', 'featureagg', 'fft_features']
fig2 = make_subplots(3,2, subplot_titles=features)
rows, cols = fig2._get_subplot_rows_columns()

spec = 'xanes'

kwargs_pca = {'mode':'markers', 'marker':dict(color=info.nn, colorscale='Viridis')} #, showscale=True, colorbar=dict(len=0.3, x=0.3, y=0.5))}
kwargs_cwt = {'colorscale':'Viridis','showscale':False} #,'colorbar':dict(len=0.3, x=1, y=0.85)}
kwargs_cdf = {}
kwargs_poly = {}
kwargs_featureagg = {'mode':'markers', 'marker':dict(color=info.nn, colorscale='Viridis')} #, showscale=True, colorbar=dict(len=0.3, x=0.6, y=0.5))}
kwargs_fft = {}

col = 1
for loc, feat, kwargs in zip(product(rows,cols), features, [kwargs_poly, kwargs_cdf, kwargs_cwt, kwargs_pca, kwargs_featureagg, kwargs_fft]): 
    row, col = loc
    arr = info.__getattribute__(spec + '_'+ feat)
    if feat == 'pca' or feat == 'featureagg': 
        pass
    else: 
        arr = arr[0].ravel()
        xaxis=info.xanes_xaxis
    temp = psf(arr, xaxis=xaxis, fig=fig2, row=row, col=col)    
    getattr(temp, f"plot_{feat}").__call__(showlegend=False, **kwargs)

fig2.show()

In [10]:

lcen_kwargs = {'l1_ratio':[0.01,0.1, 0.3, 0.5, 0.6, 0.99],
               'K_fold':5, 
               'cv_method':'Kfold', 
               'alpha':5, 
               'degree':[1],
               'trans_type':'poly', 
               'LCEN_cutoff':5e-2, 
               'LCEN_interaction':True, 
               'scale_X':True, 
               'scale_y':True}

RF_kwargs = {'estimator':RandomForestRegressor()}

In [11]:
print('hello')

hello


In [23]:
# get rid of y axis
# bar chart for feature importance

In [12]:
test_size = 0.25 
Xattr = 'xanes_pointwise_features'
yattr = 'nn'
info.do_sk(Xattr, yattr, test_size, use_pipeline=False, **RF_kwargs)
info.do_LCEN(Xattr, yattr, test_size, **lcen_kwargs)

fig = go.Figure()
info.plot_df_heatmap(pd.DataFrame(info.best_fits).T, fig, colorscale='Viridis', colorbar=dict(title='MSE'))

Beginning variable selection runs. There are 6 hyperparameter combinations
Beginning real runs. There are 36 hyperparameter combinations
Completed model LCENf fold   5
=== Residual Analysis ===
RMSE = 0.042540757591499063
APE = 1.4091970551062722
The best model is LCEN. View its results via fitting_result["LCEN"] or by opening the SPA_results json/pickle files.


In [26]:
feats = {'pointwise_features':[{'specname':'xanes', 'xrange':info.xanes_xaxis},
                               {'specname':'pdf', 'xrange':info.pdf_xaxis}],
         'polynomial_featuresall':[
             { 'specname':'xanes', 'Narr':np.array([4,5,10,20]), 'degree':3},
             { 'specname':'pdf', 'Narr':np.array([4,5,10,20]), 'degree':3}], 
        'cdf': [{ 'specname':'xanes'}],
        # 'pointwise_features_trans' : [{'specname':'xanes'}]
         }
sk_kwargs = [RF_kwargs]
multi_modal = [('xanes_pointwise_features', 'pdf_pointwise_features')] 

info.do_all(feats, 'nn', 0.25, sk_kwargs=sk_kwargs, lcen_kwargs=lcen_kwargs, 
                multi_modal=multi_modal, use_pipeline=False)

Beginning variable selection runs. There are 6 hyperparameter combinations
Beginning real runs. There are 36 hyperparameter combinations
Completed model LCENf fold   5
=== Residual Analysis ===
RMSE = 0.042540757591499063
APE = 1.4091970551062722
The best model is LCEN. View its results via fitting_result["LCEN"] or by opening the SPA_results json/pickle files.
Beginning variable selection runs. There are 6 hyperparameter combinations
Beginning real runs. There are 36 hyperparameter combinations
Completed model LCENf fold   5
=== Residual Analysis ===
RMSE = 0.06939174331256634
APE = 2.3353067853022167
The best model is LCEN. View its results via fitting_result["LCEN"] or by opening the SPA_results json/pickle files.
Beginning variable selection runs. There are 6 hyperparameter combinations
Beginning real runs. There are 36 hyperparameter combinations
Completed model LCENf fold   5
=== Residual Analysis ===
RMSE = 0.04155574283597997
APE = 1.3644274403476844
The best model is LCEN. Vie

In [28]:
fig = go.Figure()
info.plot_df_heatmap(pd.DataFrame(info.best_fits).T, fig, colorscale='Viridis', colorbar=dict(title='MSE'))

In [29]:
from spectrascope.plot_spectral_features import plot_model as pm 

In [16]:
from matplotlib.colors import rgb2hex
import matplotlib.cm as cm  
cmap = cm.get_cmap('viridis', len(selected_features))    # PiYG

viridis_hex = []
for i in range(cmap.N):
    rgba = cmap(i)
    viridis_hex.append(rgb2hex(rgba))

In [64]:
fake_coefs = np.random.random(len(selected_features))
fake_df = pd.DataFrame({x:[0,1] for x in x_temp})
fake_df = fake_df.T
# fig = make_subplots(1,1, specs=[[{"secondary_y": True}]])#, specs=[[{"secondary_y": True}, {"secondary_y": True}]], subplot_titles=['RF Feature Importances', 'LCEN Selected Features'])
fig.add_trace(go.Scatter(x=fake_df.index))
# px.scatter(fake_df.T)

In [17]:
pars = np.array(info.xanes_pointwise_features_nn_LCEN['model_params'])[:,1]
pars = [float(par) for par in pars]

In [37]:
fig = make_subplots(1,1, specs=[[{"secondary_y": True}]])#, specs=[[{"secondary_y": True}, {"secondary_y": True}]], subplot_titles=['RF Feature Importances', 'LCEN Selected Features'])


# selected_features = info.xanes_pointwise_features_nn_RandomForestRegressor['P'].feature_importances_
# plotter = pm(selected_features=selected_features, raw=info.xanes_pointwise_features[0].ravel(), fig=fig, xaxis=info.xanes_xaxis,row=1,col=1)
# plotter.plot_pointwise_features()

selected_features = info.xanes_pointwise_features_nn_LCEN['selected_features']
selected_features_arr = np.zeros_like(info.xanes_xaxis)
selected_features_arr[selected_features] = 1 
plotter = pm(selected_features=selected_features, raw=info.xanes_pointwise_features[0].ravel(), fig=fig, xaxis=info.xanes_xaxis,row=1,col=1)
plotter.plot_pointwise_features(showlegend=False)


## add invisible markers with same colorscale to get colorbar
kwargs = {'marker_size':15,'marker_symbol':'line-ns', 'marker_line_width':2,'mode':'markers', 'marker':dict(color=pars, colorscale='Viridis', showscale=True, line=dict(width=2,
                                        color=pars, colorscale='Viridis'))}
for i in np.arange(0, np.max(info.xanes_pointwise_features[0].ravel()), 0.1):
    fig.add_trace(go.Scatter(x=info.xanes_xaxis[selected_features], y = i*np.ones_like(selected_features), showlegend=False, 
                             **kwargs), row=1, col=1)

fig.show()

In [ ]:
test_size = 0.25 
Xattr = 'xanes_polynomial_featuresall'
yattr = 'nn'
info.do_sk(Xattr, yattr, test_size, use_pipeline=False, **RF_kwargs)

In [ ]:
test_size = 0.25 
Xattr = 'xanes_pca'
yattr = 'nn'
info.do_sk(Xattr, yattr, test_size, use_pipeline=False, **RF_kwargs)

In [ ]:
test_size = 0.25 
Xattr = 'xanes_featureagg'
yattr = 'nn'
info.do_sk(Xattr, yattr, test_size, use_pipeline=False, **RF_kwargs)

In [ ]:
from spectrascope.plot_spectral_features import plot_model as pm 
fig = make_subplots(1,1)
raw = info.xanes_pointwise_features[0].ravel()
selected_features = info.xanes_polynomial_featuresall_nn_RandomForestRegressor['selected_features']

plotter = pm(selected_features=selected_features, fig=fig, xaxis=info.xanes_xaxis, raw=raw)
plotter.plot_polynomial_featuresall()

fig.show()

In [ ]:
fig = make_subplots(1,1)
raw = info.xanes_featureagg
selected_features = info.xanes_featureagg_nn_RandomForestRegressor['selected_features']

kwargs_pca = {'feat':raw,'mode':'markers', 'marker':dict(color=info.nn, colorscale='Viridis', showscale=True)} #, colorbar=dict(len=0.3, x=0.3, y=0.5))}

plotter = pm(selected_features=selected_features, fig=fig, xaxis=info.xanes_xaxis, raw=raw, xaxis_label=f'aggregated feature {selected_features[0]}', yaxis_label=f'aggregated feature {selected_features[1]}')
plotter.plot_featureagg(**kwargs_pca)
fig.show()

In [ ]:
fig = make_subplots(1,1)
raw = info.xanes_pointwise_features[0].ravel()
selected_features = info.xanes_pca_nn_RandomForestRegressor['selected_features']

kwargs_pca = {'feat':info.xanes_pca, 'mode':'markers', 'marker':dict(color=info.nn, colorscale='Viridis', showscale=True)} #, showscale=True, colorbar=dict(len=0.3, x=0.3, y=0.5))}

plotter = pm(selected_features=selected_features, fig=fig, xaxis=info.xanes_xaxis, raw=raw, xaxis_label=f'PC {selected_features[0]}', yaxis_label=f'PC {selected_features[1]}')
plotter.plot_pca(**kwargs_pca)

fig.show()

In [ ]:
fig = make_subplots(1,1, specs=[[{"secondary_y": True}]])
                                
raw = info.xanes_cdf[0].ravel()
selected_features = info.xanes_pointwise_features_nn_RandomForestRegressor['P'][0].feature_importances_ 
selected_features = selected_features / np.max(selected_features)

# selected_features_arr = np.zeros_like(raw)
# selected_features_arr[selected_features] = 1 

plotter = pm(selected_features=selected_features, fig=fig, xaxis=info.xanes_xaxis, raw=raw)
plotter.plot_cdf()

fig.show()

In [ ]:
fig = make_subplots(1,1, specs=[[{"secondary_y": True}]])
raw = info.xanes_pointwise_features[0].ravel()
selected_features = info.xanes_pointwise_features_nn_RandomForestRegressor['P'][0].feature_importances_ 
selected_features = selected_features / np.max(selected_features)

plotter = pm(selected_features=selected_features, fig=fig, xaxis=info.xanes_xaxis, raw=raw)
plotter.plot_pointwise_features()

fig.show()

In [ ]:
def cubic_plots(x, a0, a1, a2, a3): 
    return a0 + a1*x + a2*(x**2) + a3*(x**3)
def const(x): 
    return cubic_plots(x, 1, 0, 0, 0)
def line(x): 
    return cubic_plots(x, 1, 100, 0, 0)
def par(x): 
    return cubic_plots(x, 1, 1, 10, 0)
def cubic(x): 
    return cubic_plots(x, 1, 1, 1, 1)

x = np.arange(-10,11,1)
plt.figure(figsize=(5,5))
plt.plot(x, const(x), linewidth=10)
plt.xticks([])
plt.yticks([])
plt.axis('off')
plt.savefig('/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/app/const.png', transparent=True)
plt.figure(figsize=(5,5))
plt.plot(x, line(x), linewidth=10, color='tab:green')
plt.xticks([])
plt.yticks([])
plt.axis('off')
plt.savefig('/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/app/line.png', transparent=True)
plt.figure(figsize=(5,5))
plt.plot(x, par(x), linewidth=10, color='tab:purple')
plt.xticks([])
plt.yticks([])
plt.axis('off')
plt.savefig('/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/app/par.png', transparent=True)       
plt.figure(figsize=(5,5))
plt.plot(x, cubic(x), linewidth=10 , color='tab:orange')
plt.xticks([])
plt.yticks([])
plt.axis('off')
plt.savefig('/Users/amalyajohnson/Desktop/Spectrascope/spectrascope_local/app/cubic.png', transparent=True )  